In [ ]:
import pandas as pd
import requests
import os
from evidently import Report
from evidently.presets import DataDriftPreset

from sklearn.model_selection import train_test_split

import sys
from pathlib import Path
project_root = Path.cwd().parents[1]
os.chdir(project_root)

from config.project_config import Api_settings, App_config


In [7]:
API_URL = f"http://localhost:{Api_settings.port}/{Api_settings.logs_inference_route}"

In [8]:
def load_reference_data(sample_size: int = 10000) -> pd.DataFrame:
    """
    Charge un échantillon du jeu d'entraînement (324 colonnes)
    """
    df_ref = pd.read_csv(App_config.paths.train_clean)

    if len(df_ref) > sample_size:
        _, df_sample = train_test_split(
            df_ref,
            test_size=sample_size,
            stratify=df_ref["TARGET"],
            random_state=42
        )
        return df_sample.reset_index(drop=True)

    return df_ref

In [9]:
def fetch_current_data(limit: int = 500) -> pd.DataFrame:
    """Récupère les données d'inferece reconstituées via l'API FastAPI."""
    try:
        response = requests.get(f"{API_URL}?limit={limit}", timeout=10)
        response.raise_for_status()

        if not response.text.strip():
            st.warning("L'API a répondu avec un corps de message vide.")
            return pd.DataFrame()

        payload = response.json()
        return pd.DataFrame(payload.get("data", []))

    except requests.exceptions.JSONDecodeError:
        st.error(f"La réponse de l'API n'est pas au format JSON. Aperçu : {response.text[:200]}")
        return pd.DataFrame()
    except requests.exceptions.RequestException as e:
        st.error(f"Erreur de connexion à l'API d'inférence : {e}")
        return pd.DataFrame()

In [10]:
ref_df = load_reference_data()
curr_df = fetch_current_data()

In [ ]:
if not curr_df.empty:   
    # Alignement optionnel des colonnes pour éviter les incompatibilités de typage
    common_cols = [col for col in ref_df.columns if col in curr_df.columns]
       
    report = Report(metrics=[DataDriftPreset()])
    snapshot = report.run(reference_data=ref_df[common_cols], current_data=curr_df[common_cols])

    display(snapshot)
else:
    print("Aucune donnée d'inférence disponible pour le moment.")

2026-08-19 23:11:05.703 WARNING streamlit.runtime.scriptrunner_utils.script_run_context: Thread 'MainThread': missing ScriptRunContext! This warning can be ignored when running in bare mode.
